In [1]:
import time
start_time = time.time()

In [2]:
!pip install --upgrade binance-historical-data PyPortfolioOpt -q

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 67.6/67.6 kB 3.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 272.8/272.8 kB 15.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 160.8/160.8 kB 5.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 4.9/4.9 MB 50.0 MB/s eta 0:00:00


In [3]:
import os
import requests
import zipfile
import numpy as np
import pandas as pd
import plotly.graph_objects as go
from math import ceil
from datetime import datetime, timedelta, date
from dateutil.relativedelta import relativedelta
from concurrent.futures import ThreadPoolExecutor, as_completed
from rich.progress import Progress
from rich.console import Console
from typing import List
from pypfopt import EfficientFrontier, expected_returns, CovarianceShrinkage, risk_models

# Tải & xử lý dữ liệu thô từ Binance

def date_range_daily(start: str, end: str):
    start_dt = datetime.strptime(start, "%Y-%m-%d")
    end_dt = datetime.strptime(end, "%Y-%m-%d")
    current = start_dt
    dates = []
    while current <= end_dt:
        dates.append(current.strftime("%Y-%m-%d"))
        current += relativedelta(days=1)
    return dates

def date_range_monthly(start: str, end: str):
    start_dt = datetime.strptime(start, "%Y-%m")
    end_dt = datetime.strptime(end, "%Y-%m")
    current = start_dt
    months = []
    while current <= end_dt:
        months.append(current.strftime("%Y-%m"))
        current += relativedelta(months=1)
    return months

def download_binance_klines_fixed_symbols(
    symbols: List[str],
    intervals: List[str],
    time_period: str,          # "daily" or "monthly"
    start: str,                # "2023-01" or "2023-01-01"
    end: str,                  # "2025-11" or "2025-12-10"
    destination_dir: str = "./binance_data",
    max_workers: int = 15,
    retries: int = 3
):
    console = Console()
    base_url = "https://data.binance.vision/data"
    asset_path = "spot"

    if time_period == "daily":
        date_list = date_range_daily(start, end)
        url_template = f"{base_url}/{asset_path}/{time_period}/klines/{{symbol}}/{{interval}}/{{symbol}}-{{interval}}-{{date}}.zip"
        csv_name_template = "{symbol}-{interval}-{date}.csv"
    elif time_period == "monthly":
        date_list = date_range_monthly(start, end)
        url_template = f"{base_url}/{asset_path}/{time_period}/klines/{{symbol}}/{{interval}}/{{symbol}}-{{interval}}-{{date}}.zip"
        csv_name_template = "{symbol}-{interval}-{date}.csv"
    else:
        raise ValueError("time_period must be 'daily' or 'monthly'")

    total_files = len(symbols) * len(intervals) * len(date_list)
    success_count = 0

    def download_one(symbol: str, interval: str, date_str: str):
        nonlocal success_count
        url = url_template.format(symbol=symbol, interval=interval, date=date_str)
        csv_name = csv_name_template.format(symbol=symbol, interval=interval, date=date_str)
        local_dir = os.path.join(destination_dir, asset_path, symbol, interval)
        local_csv = os.path.join(local_dir, csv_name)
        local_zip = local_csv.replace(".csv", ".zip")

        os.makedirs(local_dir, exist_ok=True)

        # Skip if already have CSV
        if os.path.exists(local_csv):
            return True

        for attempt in range(retries + 1):
            try:
                resp = requests.get(url, timeout=20)
                if resp.status_code == 404:
                    return False
                resp.raise_for_status()

                # Save ZIP
                with open(local_zip, "wb") as f:
                    f.write(resp.content)

                # Extract first CSV
                with zipfile.ZipFile(local_zip) as zf:
                    for name in zf.namelist():
                        if name.endswith(".csv"):
                            zf.extract(name, local_dir)
                            os.rename(os.path.join(local_dir, name), local_csv)
                            break

                os.remove(local_zip)  # optional: save disk space
                return True

            except Exception as e:
                if attempt == retries:
                    console.print(f"[red]Failed {url}: {e}[/]")
                    return False
        return False

    console.print(f"[bold blue]Total files to attempt: {total_files}[/]")

    with Progress() as progress:
        task = progress.add_task("[cyan]Downloading...", total=total_files)
        with ThreadPoolExecutor(max_workers=max_workers) as executor:
            futures = []
            for symbol in symbols:
                for interval in intervals:
                    for d in date_list:
                        futures.append(executor.submit(download_one, symbol, interval, d))

            for future in as_completed(futures):
                if future.result():
                    success_count += 1
                progress.advance(task)

    console.print(f"[bold green]Done. Successfully downloaded {success_count}/{total_files} files.[/]")

def detect_timestamp_unit(timestamp):
    num_digits = len(str(timestamp))
    if num_digits == 13:
        return 'ms'
    elif num_digits == 16:
        return 'us'
    else:
        raise ValueError(f"Timestamp không hợp lệ: {timestamp}")

def convert_timestamp(timestamp):
    unit = detect_timestamp_unit(timestamp)
    return pd.to_datetime(timestamp, unit=unit, errors='coerce')

def read_csv_file(file_path):
    df = pd.read_csv(file_path)
    df.columns = [
        "open_time", "Open", "High", "Low", "Close", "volume",
        "close_time", "quote_asset_volume", "number_of_trades",
        "taker_buy_base_asset_volume", "taker_buy_quote_asset_volume", "ignore"
    ]
    df['open_time'] = df['open_time'].apply(convert_timestamp)
    df['close_time'] = df['close_time'].apply(convert_timestamp)
    return df

def get_csv_files(directory):
    try:
        if not os.path.exists(directory):
            print(f"Warning: Thư mục không tồn tại: {directory}")
            return []
        return [os.path.join(directory, f) for f in os.listdir(directory) if f.endswith('.csv')]
    except Exception as e:
        print(f"Lỗi khi đọc thư mục {directory}: {str(e)}")
        return []

# Load data from file
def process_csv_files(ticker, data_frequency = "1h"):
    daily_path = os.path.join(os.getcwd(), f"binance_data/spot/{ticker}/{data_frequency}")
    monthly_path = os.path.join(os.getcwd(), f"binance_data/spot/{ticker}/{data_frequency}")
    daily_files = get_csv_files(daily_path)
    monthly_files = get_csv_files(monthly_path)
    all_files = daily_files + monthly_files
    if not all_files:
        print(f"❗ Không có file CSV nào cho {ticker}")
        return None
    data = pd.concat([read_csv_file(file) for file in all_files], ignore_index=True)
    data.sort_values(by='open_time', inplace=True)
    return data

# Tải & hợp nhất dữ liệu theo khung thời gian chung

def data_frequency_to_pandas_freq(freq: str) -> str:
    """Convert Binance frequency to pandas-compatible frequency string."""
    if freq.endswith('m'):
        return freq.replace('m', 'T')  # e.g., '15m' → '15T'
    elif freq == '1h':
        return 'H'
    elif freq.endswith('h'):
        return freq.replace('h', 'H')
    elif freq.endswith('d'):
        return freq.replace('d', 'D')
    elif freq.endswith('w'):
        return freq.replace('w', 'W')
    else:
        raise ValueError(f"Unsupported frequency: {freq}")

def load_multiple_tickers_with_common_range(
    tickers,
    start_time,
    end_time,
    data_frequency="1h",
    # min_fill_ratio=0.95
):
    """
    Load multiple tickers and filter them based on data completeness
    over a fixed common time range [start_time, end_time].

    A ticker is kept only if >= min_fill_ratio of its Close prices
    are valid (not NaN and > 0) within this fixed range.
    """

    # Map Binance frequency to pandas frequency
    freq_map = {
        "1m": "1T", "5m": "5T", "15m": "15T", "30m": "30T",
        "1h": "1h", "2h": "2h", "4h": "4h", "6h": "6h", "8h": "8h", "12h": "12h",
        "1d": "1D", "3d": "3D", "1w": "1W", "1M": "MS"
    }
    pd_freq = freq_map.get(data_frequency, data_frequency)

    start_time = pd.to_datetime(start_time, utc=True)
    end_time = pd.to_datetime(end_time, utc=True) + pd.Timedelta(days=1)

    # Create the full expected datetime index
    full_index = pd.date_range(start=start_time, end=end_time, freq=pd_freq)
    total_expected = len(full_index)

    all_series = []
    valid_tickers = []

    for ticker in tickers:
        try:
            # Load raw data
            print(f"Process {ticker}!")
            df = process_csv_files(ticker, data_frequency)

            # Skip if no data
            if df is None or df.empty:
                print(f"⚠️  Skipping {ticker}: no data")
                continue

            # Standardize
            df = df[["open_time", "Close"]].copy()
            df["open_time"] = pd.to_datetime(df["open_time"], utc=True)
            df.set_index("open_time", inplace=True)

            # Remove duplicates and non-positive prices
            df = df[~df.index.duplicated(keep='first')]
            df = df[df["Close"] > 0]

            # Reindex to common full range → missing = NaN
            df_reindexed = df.reindex(full_index)

            # Count valid (non-NaN) prices
            valid_count = df_reindexed["Close"].notna().sum()
            fill_ratio = valid_count / total_expected

            # if fill_ratio < min_fill_ratio:
            #     print(f"⚠️  Skipping {ticker}: fill ratio = {fill_ratio:.1%} (< {min_fill_ratio:.0%})")
            #     continue

            all_series.append(df_reindexed["Close"].rename(ticker))
            valid_tickers.append(ticker)

        except Exception as e:
            print(f"❌ Error processing {ticker}: {e}")
            continue

    if not all_series:
        print("❌ No tickers passed the fill ratio filter.")
        return pd.DataFrame()

    # Merge into a single DataFrame
    merged = pd.concat(all_series, axis=1)
    merged.sort_index(inplace=True)

    # print(f"✅ Loaded {len(valid_tickers)}/{len(tickers)} tickers with ≥{min_fill_ratio:.0%} data completeness.")
    return merged

# Lấy danh sách top ticker từ CoinGecko theo vốn hóa thị trường

def get_top_coins(n_coins: int = 10) -> list:
    """
    Lấy danh sách top N đồng coin theo vốn hóa thị trường từ CoinGecko,
    loại bỏ các stablecoin, token không mong muốn và symbol trùng lặp.

    Parameters:
    - n_coins (int): Số lượng coin muốn lấy (mặc định: 1 0)

    Returns:
    - List[str]: Danh sách symbol (viết hoa), không trùng lặp, không trong blacklist
    """
    blacklist = {
        "USDT", "USDC", "DAI", "TUSD", "UST", "WBTC", "STETH", "FIGR_HELOC", "WBT", "WSTETH",
        "WBETH", "USDS", "LEO", "BSC-USD", "HYPE", "WETH", "FDUSD", "USDP", "GUSD",
        "WEETH", "XMR", "USDE", "CBBTC", "SUSDS", "CRO", "USDT0", "PYUSD", "SUSDE", "HASH",
        "MNT", "USD1", "CC", "BGB", "OKB", "M", "USDF", "BUIDL", "JITOSOL",
        "PI", "RAIN", "JLP", "HTX", "SYRUPUSDC", "USYC", "USDG", "JSOL",
        "KCS", "RLUSD", "RSETH", "BNSOL", "WBNB", "BFUSD", "RIVER", "GT", "USDD", "RETH",
        "MYX", "KAS", "LBTC", "FBTC", "USDTB", "USTB", "USDC.E", "FLR", "SYRUPUSDT", "METH",
        "WM", "JAAA", "LSETH", "KHYPE", "USDY", "OUSG", "XDC", "SOLVBTC", "EUTBL", "USDAI",
        "COCA", "CLBTC", "BDX", "WFLR", "USD0", "JTRSY", "OSETH", "A7A5", "GHO", "EZETH",
        "IP", "JUPSOL", "STABLE", "FTN", "TBTC", "CTM", "EURC", "USR", "PIPPIN", "KAU",
        "YLDS", "SIREN"
    }

    per_page = min(250, max(100, n_coins * 3))  # gọi dư hơn để bù blacklist + duplicates
    url = "https://api.coingecko.com/api/v3/coins/markets"
    params = {
        "vs_currency": "usd",
        "order": "market_cap_desc",
        "per_page": per_page,
        "page": 1,
        "sparkline": "false"
    }

    try:
        response = requests.get(url, params=params, timeout=10)
        response.raise_for_status()
        data = response.json()
    except Exception as e:
        print(f"❌ Lỗi khi gọi API CoinGecko: {e}")
        return []

    symbols = []
    seen_symbols = set()  # theo dõi các symbol đã thêm

    for coin in data:
        symbol = coin["symbol"].upper()

        # Bỏ qua nếu đã thấy hoặc trong blacklist
        if symbol in seen_symbols or symbol in blacklist:
            continue

        symbols.append(symbol)
        seen_symbols.add(symbol)

        if len(symbols) >= n_coins:
            break

    return symbols

# Lọc tài sản (Asset Filtering)

class AssetFilter:
    def __init__(
        self,
        df,
        max_assets,
        frequency=365,
        criterion="sharpe",
        required_assets=None
    ):
        self.df = df
        self.max_assets = max_assets
        self.frequency = frequency
        self.criterion = criterion
        self.required_assets = required_assets

    def filter_top_assets(self):

        mu = expected_returns.mean_historical_return(
            self.df,
            frequency=self.frequency
        )

        daily_returns = self.df.pct_change().dropna()

        if daily_returns.isna().any().any():
            raise ValueError("The data after calculation contains NaN.")

        std_devs = daily_returns.std()
        annualized_std = std_devs * np.sqrt(self.frequency)

        # --- Ranking ---
        if self.criterion == "sharpe":
            scores = mu / annualized_std
            if isinstance(scores.index, pd.MultiIndex):
                scores.index = scores.index.map(lambda x: x[0])
            ranked = scores.sort_values(ascending=False).index.tolist()

        elif self.criterion == "volatility":
            if isinstance(annualized_std.index, pd.MultiIndex):
                annualized_std.index = annualized_std.index.map(lambda x: x[0])
            ranked = annualized_std.sort_values().index.tolist()

        else:
            raise ValueError("Criterion must be 'sharpe' or 'volatility'.")

        # --- Base selection ---
        top_assets = ranked[:self.max_assets]

        # --- Handle required_assets (list OR dict) ---
        if self.required_assets:

            if isinstance(self.required_assets, dict):
                required_list = list(self.required_assets.keys())
            elif isinstance(self.required_assets, list):
                required_list = self.required_assets
            else:
                raise ValueError("required_assets must be list or dict")

            # Remove required assets from ranked list
            top_assets = [
                asset for asset in top_assets
                if asset not in required_list
            ]

            # Add required assets to front
            top_assets = required_list + top_assets

            # Ensure uniqueness while preserving order
            top_assets = list(dict.fromkeys(top_assets))

            # Respect max_assets limit
            top_assets = top_assets[:self.max_assets]

        print("Filtered assets:", top_assets)

        return self.df[top_assets]

# Tối ưu danh mục đầu tư (Portfolio Optimization)

class PortfolioOptimizer:
    def __init__(self, df_filtered, target_return=0.2, min_weight=0.05, eur_max_weight=0.33, frequency=365, risk_model="shrinkage", required_assets=None):
        self.df_filtered = df_filtered
        self.target_return = target_return
        self.min_weight = min_weight
        self.eur_max_weight = eur_max_weight
        self.frequency = frequency
        self.risk_model = risk_model
        self.required_assets = required_assets or {}

        # --- Expected returns ---
        self.mu = expected_returns.mean_historical_return(df_filtered, frequency=frequency)

        # --- Risk model ---
        if risk_model == "shrinkage":
            self.S = CovarianceShrinkage(df_filtered, frequency=frequency).ledoit_wolf()
        elif risk_model == "sample":
            self.S = risk_models.sample_cov(df_filtered, frequency=frequency)
        elif risk_model == "semi":
            self.S = risk_models.semicovariance(df_filtered, frequency=frequency)
        elif risk_model == "exp":
            self.S = risk_models.exp_cov(df_filtered, frequency=frequency, span=60 * 24)
        elif risk_model == "exp_shrink":
            S_exp = risk_models.exp_cov(df_filtered, frequency=frequency, span=60*24)
            S_shrink = CovarianceShrinkage(df_filtered, frequency=frequency).ledoit_wolf()
            self.S = 0.5 * S_exp + 0.5 * S_shrink
        else:
            raise ValueError("Invalid risk_model")

        # --- Validate feasibility ---
        self._validate_constraints()

    def _validate_constraints(self):
        """
        Ensure sum of lower bounds <= 1
        """

        total_min = 0

        for asset in self.df_filtered.columns:
            if asset in self.required_assets:
                total_min += self.required_assets[asset]
            else:
                total_min += self.min_weight

        if total_min > 1:
            raise ValueError(f"Infeasible constraints: total minimum weight = {total_min:.2%} > 100%")

    def _add_constraints(self, ef):
        """
        Add lower bounds + EUR cap
        """

        for asset in self.df_filtered.columns:
            idx = self.df_filtered.columns.get_loc(asset)

            if asset in self.required_assets:
                min_w = self.required_assets[asset]
            else:
                min_w = self.min_weight

            ef.add_constraint(lambda w, i=idx, m=min_w: w[i] >= m)

        # EUR cap
        if "EURUSDT" in self.df_filtered.columns:
            eur_idx = self.df_filtered.columns.get_loc("EURUSDT")
            ef.add_constraint(lambda w, i=eur_idx: w[i] <= self.eur_max_weight)
        if "EURIUSDT" in self.df_filtered.columns:
            eur_idx = self.df_filtered.columns.get_loc("EURIUSDT")
            ef.add_constraint(lambda w, i=eur_idx: w[i] <= self.eur_max_weight)

    def optimize_portfolio(self):

        ef_sharpe = EfficientFrontier(self.mu, self.S)
        ef_volatility = EfficientFrontier(self.mu, self.S)
        ef_optimal = EfficientFrontier(self.mu, self.S)

        # Add constraints
        for ef in [ef_sharpe, ef_volatility, ef_optimal]:
            self._add_constraints(ef)

        # --- Max Sharpe ---
        ef_sharpe.max_sharpe()
        weights_sharpe = ef_sharpe.clean_weights()
        performance_sharpe = ef_sharpe.portfolio_performance(verbose=False)

        # --- Min Vol ---
        ef_volatility.min_volatility()
        weights_volatility = ef_volatility.clean_weights()
        performance_volatility = ef_volatility.portfolio_performance(verbose=False)

        # --- Efficient Return ---
        ef_optimal.efficient_return(target_return=self.target_return)
        weights_optimal = ef_optimal.clean_weights()
        performance_optimal = ef_optimal.portfolio_performance(verbose=False)

        # --- Pretty print ---
        def fmt_metric_and_weights(name, perf, weights):
            ret, vol, sr = perf
            print(
                f"{name:<11}: return: {ret:>6.2%} - "
                f"volatility: {vol:>6.2%} - "
                f"sharpe: {sr:>6.4f}"
            )

            active = {k: v for k, v in weights.items() if v > 0}

            if active:
                weights_str = ", ".join(
                    f"{k}: {v:.2%}"
                    for k, v in sorted(active.items(), key=lambda x: -x[1])
                )
                print(f"              Weights: {weights_str}")
            else:
                print("              Weights: (none)")

        fmt_metric_and_weights("Sharpe", performance_sharpe, weights_sharpe)
        fmt_metric_and_weights("Volatility", performance_volatility, weights_volatility)
        fmt_metric_and_weights("Optimal", performance_optimal, weights_optimal)

        return {
            "sharpe": (weights_sharpe, performance_sharpe),
            "volatility": (weights_volatility, performance_volatility),
            "optimal": (weights_optimal, performance_optimal),
        }

# Hỗ trợ tần suất & pipeline tổng hợp

# Ánh xạ timeframe → frequency (cho crypto 24/7)
TIMEFRAME_TO_FREQ = {
    '1m': 60 * 24 * 365,    # 525600
    '5m': 12 * 24 * 365,    # 105120
    '15m': 4 * 24 * 365,    # 35040
    '30m': 2 * 24 * 365,    # 17520
    '1h': 24 * 365,         # 8760
    '2h': 12 * 365,         # 4380
    '4h': 6 * 365,          # 2190
    '6h': 4 * 365,          # 1460
    '8h': 3 * 365,          # 1095
    '12h': 2 * 365,         # 730
    '1d': 365,
    '1w': 52,
    '1mo': 12,
}

def get_frequency(timeframe: str) -> int:
    if timeframe in TIMEFRAME_TO_FREQ:
        return TIMEFRAME_TO_FREQ[timeframe]
    else:
        raise ValueError(f"Unsupported timeframe: {timeframe}. Use one of {list(TIMEFRAME_TO_FREQ.keys())}")

def optimize_portfolio_pipeline(df, max_assets, min_weight, target_return, criterion, required_assets=None, eur_max_weight=0.34, timeframe='1d', risk_model="shrinkage"):
    """
    Full pipeline:
    - Filter assets (ensures required assets are included)
    - Run portfolio optimization with asset-specific lower bounds
    """

    frequency = get_frequency(timeframe)

    # --- Filter assets ---
    asset_filter = AssetFilter(df=df, max_assets=max_assets, frequency=frequency, criterion=criterion, required_assets=required_assets)

    df_filtered = asset_filter.filter_top_assets()

    # --- Optimize ---
    optimizer = PortfolioOptimizer(df_filtered=df_filtered, target_return=target_return, min_weight=min_weight, eur_max_weight=eur_max_weight, frequency=frequency, risk_model=risk_model, required_assets=required_assets)

    results = optimizer.optimize_portfolio()

    return df_filtered, results

# Định dạng & báo cáo kết quả

def format_portfolio_metrics(data):
    """
    Format kết quả portfolio optimization thành bảng Pandas:
    - Weights, return, volatility hiển thị dạng % (nhân 100 và làm tròn)
    - Sharpe ratio giữ nguyên, làm tròn 4 chữ số
    - Giữ nguyên tên tài sản đầy đủ (không rút gọn như 'B', 'P', ...)

    Input `data` có dạng:
    {
        'sharpe': ( {'BTCUSDT': 0.05, 'PAXGUSDT': 0.90, ...}, (ret, vol, sharpe) ),
        ...
    }
    """
    rows = []
    for strategy, (weights_dict, metrics) in data.items():
        row = {'strategy': strategy}
        # Giữ nguyên tên đầy đủ của tài sản
        for asset, weight in weights_dict.items():
            row[asset] = weight * 100  # chuyển trọng số sang %
        row['return'] = metrics[0] * 100      # lợi suất (%)
        row['volatility'] = metrics[1] * 100  # độ lệch chuẩn (%)
        row['sharpe'] = metrics[2]            # Sharpe (không đổi đơn vị)
        rows.append(row)

    df = pd.DataFrame(rows)
    df.set_index("strategy", inplace=True)

    # Sắp xếp cột: tài sản trước, rồi các cột metrics
    asset_cols = [col for col in df.columns if col not in ['return', 'volatility', 'sharpe']]
    metric_cols = ['return', 'volatility', 'sharpe']
    df = df[asset_cols + metric_cols]

    # Làm tròn
    percent_cols = [col for col in df.columns if col != 'sharpe']
    df[percent_cols] = df[percent_cols].round(2)
    df['sharpe'] = df['sharpe'].round(4)

    return df

def build_absolute_equal_drawdown_portfolio(
    prices: pd.DataFrame,
    assets: list[str],
    target_mdd: float,
    cash_asset: str = "EURUSDT",
):
    """
    Build long-only portfolio using absolute equal drawdown budgeting.
    Cash-like asset (e.g. EURUSDT) is treated as residual buffer
    and does NOT participate in risk budgeting.

    Parameters
    ----------
    prices : pd.DataFrame
        Price dataframe.
    assets : list[str]
        Asset universe.
    target_mdd : float
        Target portfolio max drawdown (negative, e.g. -0.10).
    cash_asset : str
        Asset treated as cash buffer.

    Returns
    -------
    dict
    """
    if target_mdd >= 0:
        raise ValueError("target_mdd must be negative")

    # --- Split assets ---
    risky_assets = [a for a in assets if a != cash_asset]

    if not risky_assets:
        raise ValueError("No risky assets provided")

    # --- Compute returns ---
    returns = prices[risky_assets].pct_change().dropna()

    # --- Compute MDDs for risky assets only ---
    asset_mdds = {}
    for asset in risky_assets:
        mdd = calculate_max_drawdown(returns[asset])

        # ensure scalar
        if isinstance(mdd, pd.Series):
            mdd = mdd.iloc[-1]

        if pd.notna(mdd) and mdd < 0:
            asset_mdds[asset] = abs(mdd)

    if not asset_mdds:
        raise ValueError("No valid risky assets with negative MDD")

    n_assets = len(asset_mdds)
    per_asset_dd = abs(target_mdd) / n_assets

    # --- Raw risky weights ---
    risky_weights = {
        asset: per_asset_dd / mdd
        for asset, mdd in asset_mdds.items()
    }

    total_risky_weight = sum(risky_weights.values())

    # --- Enforce long-only, no leverage on risky sleeve ---
    if total_risky_weight > 1.0:
        scale = 1.0 / total_risky_weight
        for a in risky_weights:
            risky_weights[a] *= scale
        total_risky_weight = 1.0

    # --- Final weights ---
    weights = dict(risky_weights)
    weights[cash_asset] = 1.0 - total_risky_weight

    return {
        "weights": weights,
        "cash_weight": weights[cash_asset],
        "asset_mdds": asset_mdds,
        "target_mdd": target_mdd,
        "per_asset_drawdown_budget": per_asset_dd,
        "regime": (
            "cash_buffered"
            if weights[cash_asset] > 0
            else "fully_risky"
        ),
    }

def generate_drawdown_benchmarks(prices, unified_assets, full_assets):
    results = {}

    for scope_name, universe in {
        "unified": unified_assets,
        "full": full_assets
    }.items():

        for target_mdd in (-0.08, -0.13, -0.21, -0.34, -0.55):

            key = f"absolute_equal_drawdown_mdd_{int(abs(target_mdd)*100)}_{scope_name}"

            try:
                ed = build_absolute_equal_drawdown_portfolio(
                    prices=prices,
                    assets=universe,
                    target_mdd=target_mdd
                )

                results[key] = ed["weights"]

            except Exception:
                continue

    return results

def compute_portfolio_returns(prices: pd.DataFrame, weights: dict) -> pd.Series:
    weights = pd.Series(weights)
    weights = weights / weights.sum()

    returns = prices[weights.index].pct_change().dropna()
    port_returns = returns.mul(weights, axis=1).sum(axis=1)

    return port_returns

def build_equal_weight(universe: list) -> dict:
    w = 1 / len(universe)
    return {a: w for a in universe}


def build_risk_parity(prices: pd.DataFrame, universe: list, timeframe: str) -> dict:
    returns = prices[universe].pct_change().dropna()

    lookback = 365 * 24 if 'h' in timeframe else 365
    returns = returns.tail(min(lookback, len(returns)))

    vols = returns.std().replace(0, np.nan).dropna()

    if vols.empty:
        return build_equal_weight(universe)

    inv = 1 / vols
    weights = inv / inv.sum()

    return weights.to_dict()

def generate_benchmarks(prices, unified_assets, full_assets, timeframe):
    benchmarks = {}

    for scope_name, universe in {
        "unified": unified_assets,
        "full": full_assets
    }.items():

        benchmarks[f"equal_weight_{scope_name}"] = build_equal_weight(universe)

        benchmarks[f"risk_parity_{scope_name}"] = build_risk_parity(
            prices, universe, timeframe
        )

    return benchmarks

def evaluate_portfolio(prices, weights, timeframe):
    returns = compute_portfolio_returns(prices, weights)
    metrics = calculate_metrics(returns, timeframe)
    return metrics

def format_portfolio_output(name, weights, metrics):
    w_str = ", ".join(f"{k}: {v:.2%}" for k, v in weights.items() if v > 0.001)

    return (
        f"{name:<12}: return: {metrics['return']:.2%} - "
        f"volatility: {metrics['volatility']:.2%} - "
        f"sharpe: {metrics['sharpe']:.4f}\n"
        f"{'':14}Weights: {w_str}"
    )

def print_portfolios(selected_portfolios):
    for name, data in selected_portfolios.items():
        weights = data["weights"]

        ret, vol, sharpe = data["metrics"]
        metrics = {
            "return": ret,
            "volatility": vol,
            "sharpe": sharpe
        }

        print(format_portfolio_output(name.capitalize(), weights, metrics))

# Grid search & lựa chọn danh mục tốt nhất

def grid_test_max_assets(
    prices,
    min_weight,
    target_return,
    criterion,
    required_assets,
    eur_max_weight,
    timeframe,
    risk_model,
    max_assets_range=range(2, 11)
):
    """
    Grid search theo max_assets + build benchmark (unified + full universe)
    """

    all_results = {}

    # ================================
    # 1. GRID SEARCH
    # ================================
    for max_assets in max_assets_range:
        print(f"\n[Grid Test] max_assets = {max_assets}")
        try:
            df_filtered, results = optimize_portfolio_pipeline(
                df=prices,
                max_assets=max_assets,
                min_weight=min_weight,
                target_return=target_return,
                criterion=criterion,
                required_assets=required_assets,
                eur_max_weight=eur_max_weight,
                timeframe=timeframe,
                risk_model=risk_model
            )
            all_results[max_assets] = (df_filtered, results)

        except Exception as e:
            print(f"  ❌ Failed for max_assets={max_assets}: {e}")
            continue

    if not all_results:
        raise ValueError("No valid portfolios generated in grid test.")

    # ================================
    # 2. COLLECT RESULTS
    # ================================
    records = []

    for max_assets, (_, results) in all_results.items():
        for strategy, (weights, metrics) in results.items():
            ret, vol, sharpe = metrics

            records.append({
                "max_assets": max_assets,
                "strategy": strategy,
                "weights": weights,
                "return": ret,
                "volatility": vol,
                "sharpe": sharpe
            })

    df_summary = pd.DataFrame(records)

    # ================================
    # 3. SELECT BEST PORTFOLIOS
    # ================================

    best_sharpe = df_summary.loc[df_summary["sharpe"].idxmax()]
    best_vol = df_summary.loc[df_summary["volatility"].idxmin()]

    feasible = df_summary[df_summary["return"] >= target_return * 0.99]

    if feasible.empty:
        print(f"⚠️ No portfolio meets target_return={target_return}. Using highest return.")
        best_optimal = df_summary.loc[df_summary["return"].idxmax()]
    else:
        best_optimal = feasible.loc[feasible["volatility"].idxmin()]

    # ================================
    # 4. BUILD UNIFIED UNIVERSE
    # ================================
    unified_assets = set()

    for record in [best_sharpe, best_vol, best_optimal]:
        for asset, w in record["weights"].items():
            if w > 0 and asset in prices.columns:
                unified_assets.add(asset)

    unified_assets = sorted(unified_assets)

    print(f"\n✓ Unified asset universe ({len(unified_assets)} assets): {unified_assets}")

    if not unified_assets:
        raise ValueError("Unified asset universe is empty.")

    # ================================
    # 5. BUILD SELECTED PORTFOLIOS
    # ================================
    selected_portfolios = {}

    for name, record in {
        "sharpe": best_sharpe,
        "volatility": best_vol,
        "optimal": best_optimal
    }.items():

        metrics = evaluate_portfolio(prices, record["weights"], timeframe)

        selected_portfolios[name] = {
            "weights": record["weights"],
            "metrics": (
                metrics["return"],
                metrics["volatility"],
                metrics["sharpe"]
            ),
            "max_assets": record["max_assets"]
        }

    # ================================
    # 6. BENCHMARKS (UNIFIED + FULL)
    # ================================
    full_assets = list(prices.columns)

    benchmarks = generate_benchmarks(
        prices=prices,
        unified_assets=unified_assets,
        full_assets=full_assets,
        timeframe=timeframe
    )

    # thêm drawdown benchmarks (chỉ unified)
    drawdown_benchmarks = generate_drawdown_benchmarks(
        prices=prices,
        unified_assets=unified_assets,
        full_assets=full_assets
    )

    benchmarks.update(drawdown_benchmarks)

    # ================================
    # 7. EVALUATE BENCHMARKS
    # ================================
    for name, weights in benchmarks.items():

        try:
            metrics = evaluate_portfolio(prices, weights, timeframe)

            selected_portfolios[name] = {
                "weights": weights,
                "metrics": (
                    metrics["return"],
                    metrics["volatility"],
                    metrics["sharpe"]
                ),
                "max_assets": len(weights)
            }

            print(f"✓ Added {name}")

        except Exception as e:
            print(f"⚠️ Skip {name}: {e}")

    print("\n" + "=" * 60)
    print("FINAL PORTFOLIOS")
    print("=" * 60)

    print_portfolios(selected_portfolios)

    return selected_portfolios

def calculate_annualized_return(returns: pd.Series, freq: str) -> float:
    periods = get_periods_per_year(freq)
    return (1 + returns.mean()) ** periods - 1


def calculate_volatility(returns: pd.Series, freq: str) -> float:
    periods = get_periods_per_year(freq)
    return returns.std() * np.sqrt(periods)


def calculate_max_drawdown(returns: pd.Series) -> float:
    cum = (1 + returns).cumprod()
    peak = cum.cummax()
    dd = (cum - peak) / peak
    return dd.min()


def calculate_metrics(returns: pd.Series, freq: str) -> dict:
    ret = calculate_annualized_return(returns, freq)
    vol = calculate_volatility(returns, freq)
    sharpe = calculate_sharpe_ratio(returns, freq)

    return {
        "return": ret,
        "volatility": vol,
        "sharpe": sharpe,
        "max_drawdown": calculate_max_drawdown(returns)
    }

def get_periods_per_year(freq: str) -> int:
    if freq.endswith('m'):  # phút
        minutes = int(freq[:-1])
        return int(365 * 24 * 60 / minutes)
    elif freq.endswith('h'):  # giờ
        hours = int(freq[:-1])
        return int(365 * 24 / hours)
    elif freq.endswith('d'):  # ngày
        return 365
    elif freq.endswith('w'):  # tuần
        return 52
    else:
        raise ValueError(f"Không hỗ trợ định dạng data_frequency: {freq}")

def calculate_sharpe_ratio(returns_series: pd.Series, data_frequency: str, annualized_risk_free_rate: float = 0.03) -> float:
    """
    Tính toán Sharpe Ratio hàng năm từ một chuỗi lợi nhuận theo kỳ.

    Args:
        returns_series (pd.Series): Chuỗi lợi nhuận của chiến lược theo từng kỳ.
        data_frequency (str): Tần suất của dữ liệu ('15m', '1H', '1D').
        annualized_risk_free_rate (float): Lãi suất phi rủi ro hàng năm.

    Returns:
        float: Giá trị Sharpe Ratio đã được quy đổi ra năm.
    """
    # Xử lý trường hợp không có giao dịch hoặc không có biến động
    if returns_series.std() == 0 or pd.isna(returns_series.std()):
        return 0.0

    # 1. Lấy số kỳ trong một năm
    periods_per_year = get_periods_per_year(data_frequency)

    # 2. Quy đổi lãi suất phi rủi ro ra theo từng kỳ
    rf_per_period = annualized_risk_free_rate / periods_per_year

    # 3. Tính toán Sharpe Ratio
    # Lợi nhuận trung bình mỗi kỳ trừ đi lãi suất phi rủi ro mỗi kỳ
    excess_return_mean = returns_series.mean() - rf_per_period

    # Sharpe Ratio hàng ngày = Lợi nhuận vượt trội trung bình / Độ lệch chuẩn lợi nhuận
    sharpe_ratio = excess_return_mean / returns_series.std()

    # 4. Quy đổi ra Sharpe Ratio hàng năm
    annualized_sharpe = sharpe_ratio * np.sqrt(periods_per_year)

    return annualized_sharpe

def plot_equity_curves_with_selected(selected: dict, prices: pd.DataFrame, timeframe: str):

    fig = go.Figure()

    for name, info in selected.items():

        weights = info["weights"]

        port_returns = compute_portfolio_returns(prices, weights)

        equity = (1 + port_returns).cumprod()
        equity = equity / equity.iloc[0]

        metrics = calculate_metrics(port_returns, timeframe)

        print(
            f"{name:<12} | "
            f"Sharpe {metrics['sharpe']:.2f} | "
            f"MDD {metrics['max_drawdown']:.2%}"
        )

        fig.add_trace(
            go.Scatter(
                x=equity.index,
                y=equity,
                mode="lines",
                name=name
            )
        )

    fig.show()

def get_start_date(
    timeframe: str,
    required_samples: int = 10000,
    end_date: datetime | None = None,
) -> tuple[datetime, int]:
    """
    Calculate start date to obtain at least `required_samples` candles.

    Parameters
    ----------
    timeframe : str
        e.g. '1m', '5m', '15m', '1h', '4h', '1d', '1w'
    required_samples : int
        Minimum number of candles required.
    end_date : datetime
        End date. Defaults to current UTC time.

    Returns
    -------
    start_date : datetime
    required_days : int
    """
    if end_date is None:
        end_date = datetime.utcnow()

    unit = timeframe[-1].lower()
    value = int(timeframe[:-1])

    if unit == "m":
        candles_per_day = 24 * 60 / value

    elif unit == "h":
        candles_per_day = 24 / value

    elif unit == "d":
        candles_per_day = 1 / value

    elif unit == "w":
        candles_per_day = 1 / (7 * value)

    else:
        raise ValueError(f"Unsupported timeframe: {timeframe}")

    required_days = ceil(required_samples / candles_per_day)
    start_date = end_date - timedelta(days=required_days)

    return start_date, required_days

In [4]:
timeframe='1h'

list_tickers = get_top_coins(8)

tickers_binance = [s + "USDT" for s in list_tickers]
extra_tickers = ["EURUSDT", "PAXGUSDT"]
tickers_binance = extra_tickers + tickers_binance

print("Top tickers:", tickers_binance)

end_date = date.today() - timedelta(days=1)
start_date, days = get_start_date(timeframe, 10000, end_date)
print(f"{timeframe:>3} -> {days:>6} days")

start_str = start_date.strftime("%Y-%m-%d")
end_str = end_date.strftime("%Y-%m-%d")

download_binance_klines_fixed_symbols(
    symbols=tickers_binance,
    intervals=[timeframe],
    time_period="daily",
    start=start_str,
    end=end_str,
    max_workers=15,
    retries = 3
)

Top tickers: ['EURUSDT', 'PAXGUSDT', 'BTCUSDT', 'ETHUSDT', 'BNBUSDT', 'XRPUSDT', 'SOLUSDT', 'TRXUSDT', 'ZECUSDT', 'DOGEUSDT']
 1h ->    417 days


Total files to attempt: 4180

Output()

Done. Successfully downloaded 4180/4180 files.

In [5]:
# Load và lọc các ticker dựa trên khung thời gian này
price_df = load_multiple_tickers_with_common_range(
    tickers=tickers_binance,
    start_time=start_str,
    end_time=end_str,
    data_frequency=timeframe,
    # min_fill_ratio=0.95
)

Process EURUSDT!
Process PAXGUSDT!
Process BTCUSDT!
Process ETHUSDT!
Process BNBUSDT!
Process XRPUSDT!
Process SOLUSDT!
Process TRXUSDT!
Process ZECUSDT!
Process DOGEUSDT!


In [6]:
price_df.ffill(inplace=True)
price_df.bfill(inplace=True)
# remove duplicated assets
price_df = price_df.loc[:, ~price_df.columns.duplicated()]

price_df


,EURUSDT,PAXGUSDT,BTCUSDT,ETHUSDT,BNBUSDT,XRPUSDT,SOLUSDT,TRXUSDT,ZECUSDT,DOGEUSDT
2025-08-16 00:00:00+00:00,1.1680,3331.70,117821.60,4487.59,836.17,3.0903,187.93,0.3536,36.86,0.23435
2025-08-16 01:00:00+00:00,1.1680,3331.70,117821.60,4487.59,836.17,3.0903,187.93,0.3536,36.86,0.23435
2025-08-16 02:00:00+00:00,1.1688,3333.89,117505.51,4444.48,831.86,3.0919,186.88,0.3528,36.45,0.23216
2025-08-16 03:00:00+00:00,1.1688,3332.28,117429.63,4432.24,831.80,3.1086,187.10,0.3528,36.20,0.23271
2025-08-16 04:00:00+00:00,1.1685,3333.32,117815.66,4453.70,836.94,3.1075,188.09,0.3546,36.35,0.23339
...,...,...,...,...,...,...,...,...,...,...
2026-10-07 20:00:00+00:00,1.1200,4122.10,83432.01,2574.52,771.15,1.4226,116.20,0.3354,1323.68,0.08891
2026-10-07 21:00:00+00:00,1.1200,4124.56,83159.21,2567.69,769.47,1.4143,115.59,0.3353,1315.10,0.08850
2026-10-07 22:00:00+00:00,1.1205,4117.03,83225.89,2569.80,771.99,1.4175,116.00,0.3351,1329.15,0.08876
2026-10-07 23:00:00+00:00,1.1204,4120.20,83321.81,2574.14,772.45,1.4215,116.30,0.3354,1327.98,0.08904


In [7]:
# === 5. Tính lợi suất ===
returns = price_df.pct_change().dropna()

# cumulative simple returns
cumulative = (1 + returns).cumprod() - 1

# tickers cần highlight
highlight = {"BTCUSDT", "EURUSDT", "EURIUSDT", "PAXGUSDT"}

fig = go.Figure()

for col in cumulative.columns:

    # set style
    line_width = 3 if col in highlight else 1
    opacity = 1

    fig.add_trace(go.Scatter(
        x=cumulative.index,
        y=cumulative[col],
        mode='lines',
        name=col,
        line=dict(width=line_width),
        opacity=opacity,
        hovertemplate='<b>%{fullData.name}:</b> %{y:.2%}<extra></extra>'
    ))

fig.update_layout(
    title="Cumulative Returns (Simple Returns)",
    xaxis_title="Time",
    yaxis_title="Cumulative Return",
    hovermode="x unified"
)

fig.show()

In [8]:
# Params
max_assets_range = range(2, 11)  # từ 2 đến 10
min_weight = 0.01
target_return = 0.01
eur_max_weight = 0.34
criterion = "sharpe"
required_assets = {
    'EURUSDT': 0.15,
    'PAXGUSDT': 0.09,
    'BTCUSDT': 0.06,
    'ETHUSDT': 0.04,
}

# Chạy grid test
selected = grid_test_max_assets(
    prices=price_df,
    min_weight=min_weight,
    target_return=target_return,
    criterion=criterion,
    required_assets=required_assets,
    eur_max_weight=eur_max_weight,
    timeframe=timeframe,
    risk_model ="exp_shrink",
    max_assets_range=max_assets_range
)

# Chuyển sang định dạng tương thích với hàm cũ
results_for_display = {
    'sharpe': (selected['sharpe']['weights'], selected['sharpe']['metrics']),
    'volatility': (selected['volatility']['weights'], selected['volatility']['metrics']),
    'optimal': (selected['optimal']['weights'], selected['optimal']['metrics'])
}


[Grid Test] max_assets = 2
Filtered assets: ['EURUSDT', 'PAXGUSDT']
Sharpe     : return: 16.79% - volatility: 20.76% - sharpe: 0.8088
              Weights: PAXGUSDT: 85.00%, EURUSDT: 15.00%
Volatility : return: 12.24% - volatility: 16.83% - sharpe: 0.7272
              Weights: PAXGUSDT: 66.00%, EURUSDT: 34.00%
Optimal    : return: 12.24% - volatility: 16.83% - sharpe: 0.7272
              Weights: PAXGUSDT: 66.00%, EURUSDT: 34.00%

[Grid Test] max_assets = 3
Filtered assets: ['EURUSDT', 'PAXGUSDT', 'BTCUSDT']
Sharpe     : return: 14.00% - volatility: 20.13% - sharpe: 0.6954
              Weights: PAXGUSDT: 79.00%, EURUSDT: 15.00%, BTCUSDT: 6.00%
Volatility : return:  5.83% - volatility: 15.94% - sharpe: 0.3658
              Weights: PAXGUSDT: 52.22%, EURUSDT: 34.00%, BTCUSDT: 13.78%
Optimal    : return:  5.83% - volatility: 15.94% - sharpe: 0.3658
              Weights: PAXGUSDT: 52.22%, EURUSDT: 34.00%, BTCUSDT: 13.78%

[Grid Test] max_assets = 4
Filtered assets: ['EURUSDT', 'PAXGU

In [9]:
plot_equity_curves_with_selected(
    selected=selected,
    prices=price_df,
    timeframe=timeframe
)

sharpe       | Sharpe 2.75 | MDD -56.09%
volatility   | Sharpe 0.12 | MDD -11.70%
optimal      | Sharpe 0.12 | MDD -11.70%
equal_weight_unified | Sharpe 1.40 | MDD -30.62%
risk_parity_unified | Sharpe 0.33 | MDD -14.25%
equal_weight_full | Sharpe 0.55 | MDD -38.44%
risk_parity_full | Sharpe -0.07 | MDD -25.31%
absolute_equal_drawdown_mdd_8_unified | Sharpe 0.19 | MDD -7.68%
absolute_equal_drawdown_mdd_13_unified | Sharpe 0.59 | MDD -8.99%
absolute_equal_drawdown_mdd_21_unified | Sharpe 0.91 | MDD -12.82%
absolute_equal_drawdown_mdd_34_unified | Sharpe 1.13 | MDD -19.14%
absolute_equal_drawdown_mdd_55_unified | Sharpe 1.21 | MDD -24.78%
absolute_equal_drawdown_mdd_8_full | Sharpe -0.23 | MDD -8.64%
absolute_equal_drawdown_mdd_13_full | Sharpe 0.02 | MDD -10.63%
absolute_equal_drawdown_mdd_21_full | Sharpe 0.25 | MDD -15.10%
absolute_equal_drawdown_mdd_34_full | Sharpe 0.42 | MDD -23.03%
absolute_equal_drawdown_mdd_55_full | Sharpe 0.52 | MDD -34.01%


In [10]:
# Params
max_assets_range = range(4, 5)  # từ 2 đến 10
min_weight = 0.01
target_return = 0.05
eur_max_weight = 0.34
criterion = "sharpe"
required_assets = {
    'EURUSDT': 0.15,
    'PAXGUSDT': 0.09,
    'BTCUSDT': 0.06,
    'ETHUSDT': 0.04,
    # 'BNBUSDT': 0.01
}

# Chạy grid test
selected_2 = grid_test_max_assets(
    prices=price_df,
    min_weight=min_weight,
    target_return=target_return,
    criterion=criterion,
    required_assets=required_assets,
    eur_max_weight=eur_max_weight,
    timeframe=timeframe,
    risk_model ="exp_shrink",
    max_assets_range=max_assets_range
)

# Chuyển sang định dạng tương thích với hàm cũ
results_for_display = {
    'sharpe': (selected_2['sharpe']['weights'], selected_2['sharpe']['metrics']),
    'volatility': (selected_2['volatility']['weights'], selected_2['volatility']['metrics']),
    'optimal': (selected_2['optimal']['weights'], selected_2['optimal']['metrics'])
}


[Grid Test] max_assets = 4
Filtered assets: ['EURUSDT', 'PAXGUSDT', 'BTCUSDT', 'ETHUSDT']
Sharpe     : return: 11.65% - volatility: 20.07% - sharpe: 0.5802
              Weights: PAXGUSDT: 75.00%, EURUSDT: 15.00%, BTCUSDT: 6.00%, ETHUSDT: 4.00%
Volatility : return:  5.54% - volatility: 16.20% - sharpe: 0.3422
              Weights: PAXGUSDT: 52.66%, EURUSDT: 34.00%, BTCUSDT: 9.34%, ETHUSDT: 4.00%
Optimal    : return:  5.54% - volatility: 16.20% - sharpe: 0.3422
              Weights: PAXGUSDT: 52.66%, EURUSDT: 34.00%, BTCUSDT: 9.34%, ETHUSDT: 4.00%

✓ Unified asset universe (4 assets): ['BTCUSDT', 'ETHUSDT', 'EURUSDT', 'PAXGUSDT']
✓ Added equal_weight_unified
✓ Added risk_parity_unified
✓ Added equal_weight_full
✓ Added risk_parity_full
✓ Added absolute_equal_drawdown_mdd_8_unified
✓ Added absolute_equal_drawdown_mdd_13_unified
✓ Added absolute_equal_drawdown_mdd_21_unified
✓ Added absolute_equal_drawdown_mdd_34_unified
✓ Added absolute_equal_drawdown_mdd_55_unified
✓ Added absolute_e

In [11]:
plot_equity_curves_with_selected(selected_2, prices=price_df, timeframe=timeframe)

sharpe       | Sharpe 0.48 | MDD -26.47%
volatility   | Sharpe 0.24 | MDD -22.26%
optimal      | Sharpe 0.24 | MDD -22.26%
equal_weight_unified | Sharpe -0.41 | MDD -36.06%
risk_parity_unified | Sharpe -0.44 | MDD -16.92%
equal_weight_full | Sharpe 0.55 | MDD -38.44%
risk_parity_full | Sharpe -0.07 | MDD -25.31%
absolute_equal_drawdown_mdd_8_unified | Sharpe -0.63 | MDD -10.81%
absolute_equal_drawdown_mdd_13_unified | Sharpe -0.50 | MDD -14.19%
absolute_equal_drawdown_mdd_21_unified | Sharpe -0.34 | MDD -19.47%
absolute_equal_drawdown_mdd_34_unified | Sharpe -0.20 | MDD -27.62%
absolute_equal_drawdown_mdd_55_unified | Sharpe -0.14 | MDD -34.45%
absolute_equal_drawdown_mdd_8_full | Sharpe -0.23 | MDD -8.64%
absolute_equal_drawdown_mdd_13_full | Sharpe 0.02 | MDD -10.63%
absolute_equal_drawdown_mdd_21_full | Sharpe 0.25 | MDD -15.10%
absolute_equal_drawdown_mdd_34_full | Sharpe 0.42 | MDD -23.03%
absolute_equal_drawdown_mdd_55_full | Sharpe 0.52 | MDD -34.01%


In [12]:
end_time = time.time()
elapsed_seconds = end_time - start_time

# Chuyển sang định dạng hh:mm:ss
hours, rem = divmod(elapsed_seconds, 3600)
minutes, seconds = divmod(rem, 60)

print(f"Thời gian xử lý: {int(hours):02d}:{int(minutes):02d}:{seconds:05.2f}")

Thời gian xử lý: 00:02:18.23
